# EnCodec Full Pipeline Test

This notebook tests the complete EnCodec pipeline:
```
audio → embeddings → codes → embeddings → audio
```

We'll test both 24kHz and 48kHz models using the `short.mp3` file.

In [1]:
import torch
import torchaudio
import numpy as np
import matplotlib.pyplot as plt
from IPython.display import Audio, display
import librosa
import os

# Import our processor
from encodec_processor import EncodecProcessor

print("✓ All imports successful")
print(f"PyTorch version: {torch.__version__}")
print(f"Torchaudio version: {torchaudio.__version__}")
print(f"CUDA available: {torch.cuda.is_available()}")

/home/esteban/Documents/projects/dev_autoencoders_tests/venv_autoencoders/lib/python3.12/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


✓ All imports successful
PyTorch version: 2.7.1+cu126
Torchaudio version: 2.7.1+cu126
CUDA available: True


## **1. Load 24kHz model and audio in such sampling rate**

In [2]:
sr=24000

# Initialize 24kHz processor
processor_24k = EncodecProcessor(sr=sr)
print(f"\nModel info:")
info = processor_24k.get_model_info()
for key, value in info.items():
    print(f"  {key}: {value}")

audio_path = "711324__cordutie__guitar_sample_fx.wav"
audio_input, _ = librosa.load(audio_path, sr=sr, mono=True)
audio_input = torch.tensor(audio_input).unsqueeze(0)  # Add batch dimension
audio_input = audio_input[:, :sr*10]

# Listen to original audio
print("\nOriginal Sound of shape ", audio_input.shape)
display(Audio(audio_input.numpy(), rate=sr))

Initializing EnCodec processor on device: cuda


/home/esteban/Documents/projects/dev_autoencoders_tests/venv_autoencoders/lib/python3.12/site-packages/torch/nn/utils/weight_norm.py:143: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  WeightNorm.apply(module, name, dim)


✓ EnCodec 24kHz model loaded (torchaudio)
✓ Sample rate: 24000 Hz
✓ Frame rate: 75 Hz

Model info:
  model_type: EnCodec 24kHz
  sample_rate: 24000
  frame_rate: 75
  device: cuda
  is_hf_model: False
  encoder_type: SEANetEncoder
  decoder_type: SEANetDecoder
  quantizer_type: ResidualVectorQuantizer

Original Sound of shape  torch.Size([1, 240000])


In [3]:
# Step 1: audio → embeddings (continuous)
print("\n1️⃣ Audio → Continuous Embeddings")
cont_embeddings_24k = processor_24k.encode_audio_emb(audio_input, sr)
print(f"   Input audio shape: {audio_input.shape}")
print(f"   Continuous embeddings shape: {cont_embeddings_24k.shape}")


1️⃣ Audio → Continuous Embeddings
   Input audio shape: torch.Size([1, 240000])
   Continuous embeddings shape: torch.Size([1, 128, 750])


In [4]:
# Step 2: audio → codes (quantized path)
print("\n2️⃣ Audio → Discrete Codes")
codes_24k, metadata_24k = processor_24k.encode_audio_codes(audio_input, kbps=24.0, sample_rate=sr)
print(f"   Discrete codes shape: {codes_24k.shape}")
print(f"   Metadata: {metadata_24k}")
print(f"   Code values range: [{codes_24k.min().item()}, {codes_24k.max().item()}]")


2️⃣ Audio → Discrete Codes
   Discrete codes shape: torch.Size([32, 1, 750])
   Metadata: None
   Code values range: [0, 1023]


In [5]:
# Step 3: codes → embeddings (quantized)
print("\n3️⃣ Discrete Codes → Quantized Embeddings")
quant_embeddings_24k = processor_24k.decode_codes_emb(codes_24k)
print(f"   Quantized embeddings shape: {quant_embeddings_24k.shape}")
print(f"   Embedding values range: [{quant_embeddings_24k.min().item():.3f}, {quant_embeddings_24k.max().item():.3f}]")


3️⃣ Discrete Codes → Quantized Embeddings
   Quantized embeddings shape: torch.Size([1, 128, 750])
   Embedding values range: [-25.744, 31.098]


In [6]:
# Step 4: embeddings → audio (both continuous and quantized)
print("\n4️⃣ Embeddings → Audio Reconstruction")

# From continuous embeddings
audio_from_cont_24k = processor_24k.decode_emb_audio(cont_embeddings_24k)
print(f"   Audio from continuous embeddings shape: {audio_from_cont_24k.shape}")

# From quantized embeddings  
audio_from_quant_24k = processor_24k.decode_emb_audio(quant_embeddings_24k)
print(f"   Audio from quantized embeddings shape: {audio_from_quant_24k.shape}")

# Direct from codes (full quantized pipeline)
audio_direct_24k = processor_24k.decode_codes_audio(codes_24k, metadata_24k)
print(f"   Audio directly from codes shape: {audio_direct_24k.shape}")


4️⃣ Embeddings → Audio Reconstruction
   Audio from continuous embeddings shape: torch.Size([1, 1, 240000])
   Audio from quantized embeddings shape: torch.Size([1, 1, 240000])
   Audio directly from codes shape: torch.Size([1, 1, 240000])


In [7]:
# Compare reconstructions
print("\n🎵 24kHz Model Audio Comparisons:")

# Get equal length samples for comparison
min_len = min(audio_input.shape[-1], audio_from_cont_24k.shape[-1], 
              audio_from_quant_24k.shape[-1], audio_direct_24k.shape[-1])

orig_24k = audio_input[..., :min_len]
cont_24k = audio_from_cont_24k[..., :min_len]
quant_24k = audio_from_quant_24k[..., :min_len]
direct_24k = audio_direct_24k[..., :min_len]

print("\nOriginal:")
display(Audio(orig_24k.squeeze().cpu().numpy(), rate=24000))

print("\nAudio -> Continuous Embeddings -> Audio")
display(Audio(cont_24k.squeeze().cpu().numpy(), rate=24000))

print("\nAudio -> Embeddings -> Codes -> Embeddings -> Audio:")
display(Audio(quant_24k.squeeze().cpu().numpy(), rate=24000))

print("\nAudio -> Embeddings -> Codes -> Audio:")
display(Audio(direct_24k.squeeze().cpu().numpy(), rate=24000))


🎵 24kHz Model Audio Comparisons:

Original:



Audio -> Continuous Embeddings -> Audio



Audio -> Embeddings -> Codes -> Embeddings -> Audio:



Audio -> Embeddings -> Codes -> Audio:


## **2. Load 48kHz model and audio in such sampling rate**

In [8]:
sr = 48000

# Initialize 48kHz processor
processor_48k = EncodecProcessor(sr=sr)
print(f"\nModel info:")
info = processor_48k.get_model_info()
for key, value in info.items():
    print(f"  {key}: {value}")

audio_path = "711324__cordutie__guitar_sample_fx.wav"
audio_input, _ = librosa.load(audio_path, sr=sr, mono=True)
audio_input = torch.tensor(audio_input).unsqueeze(0)  # Add batch dimension
audio_input = audio_input[:, :sr*10]

# Listen to original audio
print("\nOriginal Sound of shape ", audio_input.shape)
display(Audio(audio_input.numpy(), rate=sr))

Initializing EnCodec processor on device: cuda


Using a slow image processor as `use_fast` is unset and a slow processor was saved with this model. `use_fast=True` will be the default behavior in v4.52, even if the model was saved with a slow processor. This will result in minor differences in outputs. You'll still be able to use a slow processor with `use_fast=False`.


✓ EnCodec 48kHz model loaded (HuggingFace)
✓ Sample rate: 48000 Hz
✓ Frame rate: 75 Hz

Model info:
  model_type: EnCodec 48kHz
  sample_rate: 48000
  frame_rate: 75
  device: cuda
  is_hf_model: True
  encoder_type: EncodecEncoder
  decoder_type: EncodecDecoder
  quantizer_type: EncodecResidualVectorQuantizer

Original Sound of shape  torch.Size([1, 480000])


In [9]:
# Step 1: audio → embeddings (continuous)
print("\n1️⃣ Audio → Continuous Embeddings")
cont_embeddings_48k = processor_48k.encode_audio_emb(audio_input, sr)
print(f"   Input audio shape: {audio_input.shape}")
print(f"   Continuous embeddings shape: {cont_embeddings_48k.shape}")


1️⃣ Audio → Continuous Embeddings
   Input audio shape: torch.Size([1, 480000])
   Continuous embeddings shape: torch.Size([1, 128, 1635])


In [10]:
# Step 2: audio → codes (quantized path)
print("\n2️⃣ Audio → Discrete Codes")
codes_48k, metadata_48k = processor_48k.encode_audio_codes(audio_input, kbps=24.0, sample_rate=sr)
print(f"   Discrete codes shape: {codes_48k.shape}")
print(f"   Metadata keys: {list(metadata_48k.keys()) if metadata_48k else 'None'}")
if metadata_48k:
    audio_scales = metadata_48k['audio_scales']
    # padding_mask = metadata_48k['padding_mask']
    if isinstance(audio_scales, list):
        print(f"   Audio scales: list with {len(audio_scales)} items, first item shape: {audio_scales[0].shape if audio_scales else 'None'}")
    else:
        print(f"   Audio scales shape: {audio_scales.shape}")
    # print(f"   Padding mask shape: {padding_mask.shape}")
print(f"   Number of quantizers: {codes_48k.shape[1]}")
print(f"   Code values range: [{codes_48k.min().item()}, {codes_48k.max().item()}]")


2️⃣ Audio → Discrete Codes
   Discrete codes shape: torch.Size([12, 1, 16, 150])
   Metadata keys: ['audio_scales', 'padding_mask']
   Audio scales: list with 12 items, first item shape: torch.Size([1, 1])
   Number of quantizers: 1
   Code values range: [0, 1023]


In [11]:
# Step 3: codes → embeddings (quantized) - THIS IS THE KEY FIX
print("\n3️⃣ Discrete Codes → Quantized Embeddings (FIXED VERSION)")
quant_embeddings_48k = processor_48k.decode_codes_emb(codes_48k)
print(f"   Quantized embeddings shape: {quant_embeddings_48k.shape}")
print(f"   Embedding values range: [{quant_embeddings_48k.min().item():.3f}, {quant_embeddings_48k.max().item():.3f}]")
print(f"   ✓ Successfully decoded codes to embeddings with metadata!")


3️⃣ Discrete Codes → Quantized Embeddings (FIXED VERSION)
   Quantized embeddings shape: torch.Size([1, 128, 1800])
   Embedding values range: [-9.052, 10.319]
   ✓ Successfully decoded codes to embeddings with metadata!


In [12]:
# Step 4: embeddings → audio (both continuous and quantized)
print("\n4️⃣ Embeddings → Audio Reconstruction")

# From continuous embeddings
audio_from_cont_48k = processor_48k.decode_emb_audio(cont_embeddings_48k)
print(f"   Audio from continuous embeddings shape: {audio_from_cont_48k.shape}")

# From quantized embeddings  
audio_from_quant_48k = processor_48k.decode_emb_audio(quant_embeddings_48k, metadata_48k)
print(f"   Audio from quantized embeddings shape: {audio_from_quant_48k.shape}")

# Direct from codes (full quantized pipeline)
audio_direct_48k = processor_48k.decode_codes_audio(codes_48k, metadata_48k)
print(f"   Audio directly from codes shape: {audio_direct_48k.shape}")


4️⃣ Embeddings → Audio Reconstruction
   Audio from continuous embeddings shape: torch.Size([1, 2, 523200])
   Audio from quantized embeddings shape: torch.Size([1, 2, 523200])
   Audio directly from codes shape: torch.Size([1, 2, 570720])


In [13]:
# Compare reconstructions
print("\n🎵 48kHz Model Audio Comparisons:")

# Get equal length samples for comparison
min_len = min(audio_input.shape[-1], audio_from_cont_48k.shape[-1], 
              audio_from_quant_48k.shape[-1], audio_direct_48k.shape[-1])

# Resample original to 48kHz for fair comparison
orig_48k = audio_input[..., :min_len]
cont_48k = audio_from_cont_48k[..., :min_len]
quant_48k = audio_from_quant_48k[..., :min_len]
direct_48k = audio_direct_48k[..., :min_len]

print("\nOriginal (resampled to 48kHz):")
display(Audio(orig_48k.squeeze().cpu().numpy(), rate=48000))

print("\nFrom Continuous Embeddings:")
display(Audio(cont_48k.squeeze().cpu().numpy(), rate=48000))

print("\nFrom Quantized Embeddings (codes→embeddings→audio):")
display(Audio(quant_48k.squeeze().cpu().numpy(), rate=48000))

print("\nDirect from Codes (codes→audio):")
display(Audio(direct_48k.squeeze().cpu().numpy(), rate=48000))


🎵 48kHz Model Audio Comparisons:

Original (resampled to 48kHz):



From Continuous Embeddings:



From Quantized Embeddings (codes→embeddings→audio):



Direct from Codes (codes→audio):
